<br>
<font>
<div dir=ltr align=center>
<div dir=ltr align=center>
<font color=0F5298 size=7>
    Artificial Intelligence <br>
<font color=2565AE size=5>
    Computer Engineering Department <br>
    Arash Marioriyad<br>
    Spring 2026<br>
<font color=3C99D size=5>
    Practical HomeWork 2<br>
    Nonogram<br>
<font color=696880 size=4>
    Foad Kheirabady

`Full Name:` Sobhan Aram

# Introduction

In this notebook, you will implement several algorithms for solving **Constraint Satisfaction Problems (CSPs)**.
We begin with a **baseline brute-force solver** that assigns values blindly and uses **backtracking** when a constraint is violated.
You will then progressively enhance it with:

- **Forward Checking** – pruning inconsistent domain values after each assignment,
- **Minimum Remaining Values (MRV)** – always choosing the most constrained variable next,
- **Arc Consistency (AC-3)** – enforcing global consistency across all variable domains.

## What is a CSP?

A **Constraint Satisfaction Problem** is defined by three components:

- **Variables:** the unknowns we need to assign values to.
- **Domains:** the set of possible values each variable can take.
- **Constraints:** rules restricting which combinations of values are valid.

## Nonogram as a CSP

**Nonograms** (also known as Picross or Griddlers) are grid-based logic puzzles.
Each cell in an $N \times M$ grid must be filled ($1$) or left empty ($0$).
The valid pattern is determined by **clues** given for each row and column.

A clue is a sequence of integers indicating the lengths of consecutive filled-cell blocks, in left-to-right
(or top-to-bottom) order, with **at least one empty cell** between consecutive blocks.

**Example:** the clue `[2, 1]` for a row of length 5 means: a block of 2 filled cells, at least one gap, then a block of 1 filled cell.
Valid arrangements include `11010`, `11001`, `01101`.

We model this as a CSP:

- **Variables:** every cell $(i, j)$ in the $N \times M$ grid.
- **Domain:** $\{0, 1\}$ for each cell ($0$ = empty, $1$ = filled).
- **Constraints:** for each row $i$, the sequence of filled cells must match `row_clues[i]`;
  for each column $j$, it must match `col_clues[j]`.
- **Neighbors** of $(i, j)$: all other cells sharing the same row or column.

An example Nonogram puzzle is shown below.

![Example Nonogram](Nonogram-of-a-Dolphin.webp)

## Helper Functions in `utils.py`

Two utility functions are provided and are **free to use** throughout this notebook:

| Function | Description |
|---|---|
| `get_valid_arrangements(clue, length)` | Returns **all** valid binary lists of the given length satisfying the clue. |
| `is_line_possible(values, clue)` | Given a partial line (list with $-1$ for unassigned), returns `True` if the clue can still be satisfied. |

Study these helpers before starting — they are the key building blocks for every solver.


## Grading
| Chapter | Points |
|---|---|
| Baseline Solver | 10 |
| Forward Checking | 30 |
| MRV | 10 |
| AC-3 | 50 |

**NOTE 1:** All value assignments **must** use the **`state.assign`** function.
Direct modification of the grid outside this function may result in loss of the chapter's grade.

**NOTE 2:** Runtime optimization is encouraged but not required — the key metric is the **number of assignments**.

**NOTE 3:** You earn chapter points only if your solver makes **fewer assignments** than the previous solver.

**NOTE 4:** Two examples are used throughout this notebook to evaluate each solver:
- **First Example (15×15)** — a moderately complex puzzle used for **testing and debugging**.
  It is intentionally designed to take 5–10 seconds on the baseline solver, giving a clear
  signal that each successive solver is making meaningful improvements in assignments and backtracks.
- **Second Example (15×20)** — the **main benchmark puzzle**. This is the primary puzzle
  on which solvers are graded. It is significantly harder and may take a long time on weaker solvers.
  
> ⚠️ **Important:** Each solver must show a measurable reduction in the number of assignments
> on **both** examples compared to the previous solver. Pay close attention to the second example
> — it is the one that determines your grade.

In [1]:
import time
from collections import deque

import numpy as np

from models import NonogramCSP, Cell, StepLogger
from utils import (
    build_nonogram_csp, make_animation,
    get_valid_arrangements, is_line_possible,
    ROW_CLUES_1, COL_CLUES_1,
    ROW_CLUES_2, COL_CLUES_2
)


# Baseline Solver — 10 Points

In this chapter, implement the **baseline backtracking solver**.

Strategy:
- Iterate through cells in row-major order (left to right, top to bottom).
- For each unassigned cell, try each value in $\{0, 1\}$.
- If the value violates any constraint, skip it.
- If neither value works, **backtrack** to the previous assignment.

Do **not** use forward checking, MRV, or any domain pruning at this stage.

**Consistency check:** after tentatively assigning a value, call `is_line_possible`
on the current row and the current column. If either fails, the value is invalid.

## The `ValuesState` Class

`ValuesState` tracks the current assignment.  The grid is a NumPy array initialised
to $-1$ (unassigned). Always use **`state.assign`** to update a cell — it handles
the step logger so the animation remains consistent.

In [2]:
class ValuesState:
    assignment: np.ndarray  

    def __init__(self, csp: NonogramCSP):
        self.assignment = np.full((csp.N, csp.M), -1, dtype=int)

    def assign(self, cell: Cell, v: int, csp: NonogramCSP, logger: StepLogger):
        """
        Assign value v to cell.
        Pass v = -1 to undo an assignment (backtrack).
        """
        if v == -1:
            logger.log("backtrack", cell, int(self.assignment[cell]))
        else:
            logger.log("assign", cell, v)
        self.assignment[cell] = v

In [3]:
def solve_baseline(csp: NonogramCSP, state: ValuesState, logger: StepLogger) -> bool:

    def is_consistent(cell: Cell, value: int) -> bool:

        cell_row = cell[0]
        cell_column = cell[1]

        M = csp.M
        current_row = []
        for i in range(M):
            if(i == cell_column):
                current_row.append(int(value))
            else:
                current_row.append(int(state.assignment[cell_row, i]))

        if(is_line_possible(current_row, csp.row_clues[cell_row]) == False):
            return False
        

        N = csp.N
        current_column = []
        for i in range(N):
            if(i == cell_row):
                current_column.append(int(value))
            else:
                current_column.append(int(state.assignment[i, cell_column]))

        if(is_line_possible(current_column, csp.col_clues[cell_column]) == False):
            return False
        
        return True

    def backtrack() -> bool:

    

        cell_to_back_track = None

        for cell in csp.variables:
            if(state.assignment[cell] == -1):
                cell_to_back_track = cell
                break

        if(cell_to_back_track == None):
            return True
    
        if(is_consistent(cell, 0)):
            state.assign(cell, 0, csp, logger)

            if(backtrack() == True):
                return True
            
            else:
                state.assign(cell, -1, csp, logger)

        if(is_consistent(cell, 1)):
            state.assign(cell, 1, csp, logger)

            if(backtrack() == True):
                return True
            
            else:
                state.assign(cell, -1, csp, logger)

        return False
    
                

    return backtrack()

In [4]:
# Set to True to also run the second (harder) 15×20 example.
# Warning: it may take significantly longer to solve.
RUN_SECOND_EXAMPLE = True

def run_example(label, row_clues, col_clues, timeout=None):
    import threading

    csp    = build_nonogram_csp(row_clues, col_clues)
    logger = StepLogger()
    state  = ValuesState(csp)

    result = {"ok": None, "runtime": None, "timed_out": False}

    def _solve():
        t0 = time.time()
        result["ok"]      = solve_baseline(csp, state, logger)
        result["runtime"] = time.time() - t0

    thread = threading.Thread(target=_solve, daemon=True)
    thread.start()
    thread.join(timeout)

    if thread.is_alive():
        result["timed_out"] = True
        result["runtime"]   = timeout

    num_assigns    = sum(1 for e in logger.events if e.action == "assign")
    num_prunes     = sum(1 for e in logger.events if e.action == "prune")
    num_backtracks = sum(1 for e in logger.events if e.action == "backtrack")

    print(f"\n{label}")
    if result["timed_out"]:
        print(f"Solved:      TIMED OUT after {timeout}s")
    else:
        print(f"Solved:      {result['ok']}")
    print(f"Runtime:     {result['runtime']:.3f} seconds")
    print(f"Assignments: {num_assigns}")
    print(f"Prunes:      {num_prunes}")
    print(f"Backtracks:  {num_backtracks}")

    return csp, logger


csp1, logger1 = run_example("First Example (15×15)", ROW_CLUES_1, COL_CLUES_1)

csp2, logger2 = None, None
if RUN_SECOND_EXAMPLE:
    csp2, logger2 = run_example("Second Example (15×20)", ROW_CLUES_2, COL_CLUES_2)



First Example (15×15)
Solved:      True
Runtime:     0.852 seconds
Assignments: 780
Prunes:      0
Backtracks:  555

Second Example (15×20)
Solved:      True
Runtime:     77.867 seconds
Assignments: 19317
Prunes:      0
Backtracks:  19017


In [5]:
make_animation(csp1, logger1, fps=5, last_k=150, stride=1)

if csp2 is not None:
    make_animation(csp2, logger2, fps=5, last_k=150, stride=1)

# Forward Checking — 30 Points

In this chapter, extend the baseline solver with **forward checking**.

After each assignment to cell $(r, c)$, inspect **row $r$** and **column $c$**:

1. Compute all valid arrangements of that line consistent with the current assignment
   (use `get_valid_arrangements`, then filter by the current partial state).
2. For each **unassigned** cell in the line, determine which values still appear
   in at least one valid arrangement.
3. **Prune** values that never appear.
4. If any unassigned cell's domain becomes **empty**, the current branch fails — backtrack immediately.

Do **not** use the MRV heuristic yet; keep assigning cells in row-major order.

## The `DomainValuesState` Class

`DomainValuesState` extends `ValuesState` with per-cell `domains`.  
Always use **`state.prune`** and **`state.unprune`** to change domains — never
modify `domains` directly. These methods also update the step logger.

In [6]:
class DomainValuesState(ValuesState):
    domains: dict   # Cell -> set of remaining values  {0, 1}

    def __init__(self, csp: NonogramCSP):
        super().__init__(csp)
        self.domains = {cell: {0, 1} for cell in csp.variables}

    def prune(self, cell: Cell, v: int, logger: StepLogger):
        self.domains[cell].discard(v)
        logger.log("prune", cell, v)

    def unprune(self, cell: Cell, v: int):
        self.domains[cell].add(v)

In [7]:
def solve_forward_check(csp: NonogramCSP, state: DomainValuesState, logger: StepLogger) -> bool:
    """
    Solve using backtracking + one-step forward checking.

    After assigning a cell (r, c), call forward_check(r, c) which:
      - Checks row r and column c.
      - Prunes values from unassigned cells in those lines that are not
        supported by any valid arrangement.
      - Returns the list of (cell, value) pairs pruned, or None on failure.

    On backtracking, restore all pruned values with state.unprune.

    Returns True if solved, False otherwise.
    """

    def check_line(cells: list, clue: tuple, length: int):

        all_possible_arrangements = get_valid_arrangements(clue, length)
        good_arrangements = []

        n = len(cells)
        for arragement in all_possible_arrangements:
            index = 0
            valid = 1
            while(index < n):
                if(state.assignment[cells[index]] == -1):
                    exist = 0
                    for value in state.domains[cells[index]]:
                        if(value == arragement[index]):
                            exist = 1

                    if(exist == 0):
                        valid = 0
                        break

                else:
                    if(arragement[index] != state.assignment[cells[index]]):
                        valid = 0
                        break

                
                index += 1

            if(valid == 1):
                good_arrangements.append(arragement)



        if(len(good_arrangements) == 0):
            return None

                

        all_pruned = []        
        for index in range(n):
            if(state.assignment[cells[index]] == -1):
                valid_choices = []
                for arrangement in good_arrangements:
                    if(arrangement[index] not in valid_choices):
                        valid_choices.append(arrangement[index])

                is_new_domain_empty = True
                for choice in state.domains[cells[index]]:
                    if(choice in valid_choices):
                        is_new_domain_empty = False
                
                if(is_new_domain_empty):
                    return None
                
                for choice in state.domains[cells[index]]:
                    if(choice not in valid_choices):
                        all_pruned.append((cells[index] , choice))

        for cell, value in all_pruned:
            state.prune(cell, value, logger)
                        

        return all_pruned
    


    def forward_check(r: int, c: int):

        r_row = []
        for i in range(csp.M):
            r_row.append((r, i))

        c_column = []
        for i in range(csp.N):
            c_column.append((i, c))

        pruned_row = check_line(r_row, csp.row_clues[r], csp.M)
        if(pruned_row == None):
            return None
        
        pruned_column = check_line(c_column, csp.col_clues[c], csp.N)
        if(pruned_column == None):
            for prune in pruned_row:
                state.unprune(prune[0], prune[1])
            return None
        

        for prune in pruned_column:
            pruned_row.append(prune)

        return pruned_row

    def backtrack() -> bool:
    
        cell_to_back_track = None

        for cell in csp.variables:
            if(state.assignment[cell] == -1):
                cell_to_back_track = cell
                break
        
        if(cell_to_back_track == None):
            return True

        for v in list(state.domains[cell_to_back_track]):
            state.assign(cell_to_back_track, v, csp, logger)
            pruned = forward_check(cell_to_back_track[0], cell_to_back_track[1])

            if(pruned != None):
                if(backtrack() == True):
                    return True
                
                else:
                    for cell2, value in pruned:
                        state.unprune(cell2, value)

                    state.assign(cell_to_back_track, -1, csp, logger)

            else:
                state.assign(cell_to_back_track, -1, csp, logger)

        return False
        



            
    

    return backtrack()


In [8]:
def run_example_fc(label, row_clues, col_clues, timeout=None):
    import threading

    csp    = build_nonogram_csp(row_clues, col_clues)
    logger = StepLogger()
    state  = DomainValuesState(csp)

    result = {"ok": None, "runtime": None, "timed_out": False}

    def _solve():
        t0 = time.time()
        result["ok"]      = solve_forward_check(csp, state, logger)
        result["runtime"] = time.time() - t0

    thread = threading.Thread(target=_solve, daemon=True)
    thread.start()
    thread.join(timeout)

    if thread.is_alive():
        result["timed_out"] = True
        result["runtime"]   = timeout

    num_assigns    = sum(1 for e in logger.events if e.action == "assign")
    num_prunes     = sum(1 for e in logger.events if e.action == "prune")
    num_backtracks = sum(1 for e in logger.events if e.action == "backtrack")

    print(f"\n{label}")
    if result["timed_out"]:
        print(f"Solved:      TIMED OUT after {timeout}s")
    else:
        print(f"Solved:      {result['ok']}")
    print(f"Runtime:     {result['runtime']:.3f} seconds")
    print(f"Assignments: {num_assigns}")
    print(f"Prunes:      {num_prunes}")
    print(f"Backtracks:  {num_backtracks}")

    return csp, logger


csp1_fc, logger1_fc = run_example_fc("First Example (15×15)", ROW_CLUES_1, COL_CLUES_1)

csp2_fc, logger2_fc = None, None
if RUN_SECOND_EXAMPLE:
    csp2_fc, logger2_fc = run_example_fc("Second Example (15×20)", ROW_CLUES_2, COL_CLUES_2)




First Example (15×15)
Solved:      True
Runtime:     0.332 seconds
Assignments: 306
Prunes:      212
Backtracks:  81

Second Example (15×20)
Solved:      True
Runtime:     20.854 seconds
Assignments: 7735
Prunes:      8887
Backtracks:  7435


In [9]:
make_animation(csp1_fc, logger1_fc, fps=5, last_k=150, stride=1)

if csp2_fc is not None:
    make_animation(csp2_fc, logger2_fc, fps=5, last_k=150, stride=1)

Discuss your results. In what ways did forward checking improve over the baseline? Is it always faster?

`Your Answer:`


با توجه به اعداد بدست آمده می بینیم که روش فوروارد چکینگ در هر دو مثال ما با هرس کردن تعداد از مسیر ها، باعث کاهش تعداد اساینمت ها و بک ترک های مورد نیاز برای حل سوال شده است. که در نتیجه باعث بهبود زمانی حل سوال شده است.

این روش باعث می شود که زودتر از بک ترک عادی متوجه شویم که یک مسیر بن بست است و به جواب نخواهد رسید و آن را هرس می کنیم. یعنی با اینکار فضایی از حالات که باید جست و جو شود کمتر می شود و کار را برای ما راحت تر می کند و همچنین از گیر افتادن در بعضی از حالات مارا نجات می دهد.

اما همیشه این روش باعث بهبود عملگرد نمی شود چرا که در هر مرحله بروزرسانی دامنه های همسایه های راس فعلی، یک هزینه ی سرباری دارد که ممکن است همیشه به تعداد مسیر هایی که هرس می شوند نیرزد. مثلا اگر فضای مسئله بسیار کوچک باشد هرس ها در صورت اتفاق افتادن هم ممکن است بسیار کوچک باشند به گونه ای که هزینه ی سربار آپدیت کردن دامنه هارا جبران نکنند و سرجمع باعث کاهش کارایی الگوریتم شوند.








# Minimum Remaining Values (MRV) — 10 Points

In this chapter, add the **MRV heuristic** on top of forward checking.

Instead of assigning cells in fixed row-major order, always pick the **unassigned cell
with the fewest remaining domain values**.  Targeting the most constrained cell first
tends to expose failures earlier, pruning large branches of the search tree.

Continue using **one-step forward checking** (exactly as in Chapter 2) after each assignment.

## The `MRVState` Class

`MRVState` extends `DomainValuesState` with a `num_remaining_values` array for fast
MRV lookups.  Pruning and unpruning automatically keep this count consistent.

In [10]:
class MRVState(DomainValuesState):
    num_remaining_values: np.ndarray   # shape (N, M)

    def __init__(self, csp: NonogramCSP):
        super().__init__(csp)
        self.num_remaining_values = np.full((csp.N, csp.M), 2, dtype=int)

    def prune(self, cell: Cell, v: int, logger: StepLogger):
        self.domains[cell].discard(v)
        self.num_remaining_values[cell] -= 1
        logger.log("prune", cell, v)

    def unprune(self, cell: Cell, v: int):
        self.domains[cell].add(v)
        self.num_remaining_values[cell] += 1

In [11]:
def solve_mrv(csp: NonogramCSP, state: MRVState, logger: StepLogger) -> bool:
    """
    Solve using backtracking + forward checking + MRV variable ordering.

    Replace the fixed-order cell selection with select_unassigned(), which
    returns the unassigned cell with the smallest domain
    (use state.num_remaining_values for efficiency).

    The forward_check logic is identical to Chapter 2.

    Returns True if solved, False otherwise.
    """

    def select_unassigned() -> Cell:    
        selected_cell = None
        minimum_domain_size= float('inf')
        for cell in csp.variables:
            if(state.assignment[cell] == -1):
                if (state.num_remaining_values[cell] < minimum_domain_size):
                    minimum_domain_size = state.num_remaining_values[cell]
                    selected_cell = cell
        return selected_cell


        


    def check_line(cells: list, clue: tuple, length: int):

        all_possible_arrangements = get_valid_arrangements(clue, length)
        good_arrangements = []

        n = len(cells)
        for arragement in all_possible_arrangements:
            index = 0
            valid = 1
            while(index < n):
                if(state.assignment[cells[index]] == -1):
                    exist = 0
                    for value in state.domains[cells[index]]:
                        if(value == arragement[index]):
                            exist = 1

                    if(exist == 0):
                        valid = 0
                        break

                else:
                    if(arragement[index] != state.assignment[cells[index]]):
                        valid = 0
                        break

                
                index += 1

            if(valid == 1):
                good_arrangements.append(arragement)



        if(len(good_arrangements) == 0):
            return None

                

        all_pruned = []        
        for index in range(n):
            if(state.assignment[cells[index]] == -1):
                valid_choices = []
                for arrangement in good_arrangements:
                    if(arrangement[index] not in valid_choices):
                        valid_choices.append(arrangement[index])

                is_new_domain_empty = True
                for choice in state.domains[cells[index]]:
                    if(choice in valid_choices):
                        is_new_domain_empty = False
                
                if(is_new_domain_empty):
                    return None
                
                for choice in state.domains[cells[index]]:
                    if(choice not in valid_choices):
                        all_pruned.append((cells[index] , choice))

        for cell, value in all_pruned:
            state.prune(cell, value, logger)
                        

        return all_pruned

    def forward_check(r: int, c: int):
        
        r_row = []
        for i in range(csp.M):
            r_row.append((r, i))

        c_column = []
        for i in range(csp.N):
            c_column.append((i, c))

        pruned_row = check_line(r_row, csp.row_clues[r], csp.M)
        if(pruned_row == None):
            return None
        
        pruned_column = check_line(c_column, csp.col_clues[c], csp.N)
        if(pruned_column == None):
            for prune in pruned_row:
                state.unprune(prune[0], prune[1])
            return None
        

        for prune in pruned_column:
            pruned_row.append(prune)

        return pruned_row

    def backtrack() -> bool:
        
        cell_to_back_track = select_unassigned()
        
        if(cell_to_back_track == None):
            return True

        for v in list(state.domains[cell_to_back_track]):
            state.assign(cell_to_back_track, v, csp, logger)
            pruned = forward_check(cell_to_back_track[0], cell_to_back_track[1])

            if(pruned != None):
                if(backtrack() == True):
                    return True
                
                else:
                    for cell2, value in pruned:
                        state.unprune(cell2, value)

                    state.assign(cell_to_back_track, -1, csp, logger)

            else:
                state.assign(cell_to_back_track, -1, csp, logger)

        return False

    return backtrack()

In [12]:
def run_example_mrv(label, row_clues, col_clues, timeout=None):
    import threading

    csp    = build_nonogram_csp(row_clues, col_clues)
    logger = StepLogger()
    state  = MRVState(csp)

    result = {"ok": None, "runtime": None, "timed_out": False}

    def _solve():
        t0 = time.time()
        result["ok"]      = solve_mrv(csp, state, logger)
        result["runtime"] = time.time() - t0

    thread = threading.Thread(target=_solve, daemon=True)
    thread.start()
    thread.join(timeout)

    if thread.is_alive():
        result["timed_out"] = True
        result["runtime"]   = timeout

    num_assigns    = sum(1 for e in logger.events if e.action == "assign")
    num_prunes     = sum(1 for e in logger.events if e.action == "prune")
    num_backtracks = sum(1 for e in logger.events if e.action == "backtrack")

    print(f"\n{label}")
    if result["timed_out"]:
        print(f"Solved:      TIMED OUT after {timeout}s")
    else:
        print(f"Solved:      {result['ok']}")
    print(f"Runtime:     {result['runtime']:.3f} seconds")
    print(f"Assignments: {num_assigns}")
    print(f"Prunes:      {num_prunes}")
    print(f"Backtracks:  {num_backtracks}")

    return csp, logger


csp1_mrv, logger1_mrv = run_example_mrv("First Example (15×15)", ROW_CLUES_1, COL_CLUES_1)

csp2_mrv, logger2_mrv = None, None
if RUN_SECOND_EXAMPLE:
    csp2_mrv, logger2_mrv = run_example_mrv("Second Example (15×20)", ROW_CLUES_2, COL_CLUES_2)



First Example (15×15)
Solved:      True
Runtime:     0.282 seconds
Assignments: 231
Prunes:      173
Backtracks:  6

Second Example (15×20)
Solved:      True
Runtime:     0.761 seconds
Assignments: 300
Prunes:      299
Backtracks:  0


In [13]:
make_animation(csp1_mrv, logger1_mrv, fps=5, last_k=150, stride=1)

if csp2_mrv is not None:
    make_animation(csp2_mrv, logger2_mrv, fps=5, last_k=150, stride=1)

Compare your results to the previous solvers. How did MRV affect assignments and backtracks? Why does choosing the most constrained cell first help?


`Your Answer:`

می بینیم که با اعمال کردن قاعده ی ام آر وی همراه با روش قبل، جفت الگوریتم ها بهبود به شدت چشمگیری داشتند. و تقریبا به بهترین حالت خود رسیدند. 

بدون استفاده از این قاعده در انتخاب متغیر ها برای مقدار دهی، متغیر بعدی طبق ترتیب قابتی انتخاب می شود که هوشمندانه نیست و به جریان طی شده ی مسئله تا به الان توجه نمی کند. ولی با استفاده از قاعده ی ام آر وی ما به سراغ انتخاب ولیوی متفیری می رویم که بیشتر از باقی متغیر ها تخت فشار است و باعث می شود که زودتر بفهمیم که این شاخه مناسب بوده یا خیر. یعنی انتخاب متغیری که بیشترین محدودیت روی ولیو ها را دارد کمک می کند که اگر این شاخه نامناسب است، زودتر مشحص شود که شکست خواهد خورد.

این موضوع باعث می شود که زودتر مسیر های اشتباه را تشخیص داده و در نتیجه اساینمنت ها و بک ترک های کمتری انجام دهیم تا به جواب نهایی برسیم.

به چندین دلیل انتخاب محدودترین متغیر مناسب تر است. چرا که اولا وقتی محدود ترین متغیر را برای مقدار دهی انتخاب می کنیم، تعداد انشعاب هایی که از این مرحله به مرحله ی بعد ایجاد می شود کمترین حالت است و فضای بررسی حالت های محلی رو کمینه می کند.

دلیل دیگر این است که انتخاب این متغیر باعث می شود سریعتر بن بست های پیش رو را شناسایی کنیم مثلا فرض کنید که متغیری داریم که فقط ۱ مقدار برای آن باقی مانده پس ناچارا باید همان مقدار را بگیرد که ممکن است در مرحله ی بعد باعث هرس این شاخه شود. در کل اگر بخشی از مسئله که روی آن محدودیت بیشتری است و حالت های کمتری دارد جواب نداشته باشد باعث می شود که زودتر بفهمیم که مسئله ی اصلی مان یعنی شاخه ای که الان در آن هستیم جواب ندارد و هرس شود.

همچنین ترکیب آن با فوروارد چکینگ کمک می کند که زودتر دامنه های متغیر ها آپدیت شوند و محدودیت هایشان آشکار شود.

# Arc Consistency (AC-3) — 50 Points

In this chapter, integrate **AC-3** into the MRV solver.

### Why AC-3?

Forward checking only re-examines the **two lines** directly touched by the most recent
assignment.  AC-3 goes further: whenever a pruning changes a cell's domain, it re-queues
**all other lines containing that cell**, propagating the constraint like a cascade.
This often eliminates many values (or forces assignments) long before backtracking would
reach those cells.

### AC-3 for Nonogram

An **arc** here corresponds to a **line** — a complete row or column.  The AC-3 queue holds
`('row', i)` and `('col', j)` items.

**Algorithm:**

1. Seed the queue (all lines at startup; just the affected row and column after an assignment).
2. Dequeue a line and compute all valid arrangements consistent with current assignments and domains.
3. For each unassigned cell in the line, prune values absent from every valid arrangement.
4. If a cell's domain **changed**, add its **other-dimension** line back to the queue
   (`'col'` for a cell in a row, and `'row'` for a cell in a column).
5. If any domain becomes empty, return failure.

Continue using **MRV** for cell selection.

**Implementation note:** `ac3` should return `(success: bool, pruned: list)`.
On backtracking, restore all items in `pruned` with `state.unprune`.

**Hint:** call `ac3()` once before the first assignment to reduce domains globally.

In [14]:
def solve_ac3_mrv(csp: NonogramCSP, state: MRVState, logger: StepLogger) -> bool:
    """
    Solve using backtracking + AC-3 propagation + MRV variable ordering.

    ac3(initial_queue):
      - If initial_queue is None, seed with all rows and columns.
      - Otherwise seed with the provided list of ('row'/'col', idx) items.
      - Propagate until the queue is empty or a domain becomes empty.
      - Return (success, all_pruned).

    On backtrack: restore all pruned values, then undo the assignment.

    Returns True if solved, False otherwise.
    """

    def ac3(initial_queue=None):

        if(initial_queue == None):
            queue = deque()
            for i in range(csp.N):
                queue.append(i + 1)

            for i in range(csp.M):
                queue.append(-(i + 1))

        else:
            queue = deque(initial_queue)

        all_pruned = []

        while queue:
            popped = queue.popleft()

            valid_arrangments = None
            cells = []
            if(popped > 0):
                for i in range(csp.M):
                    cells.append((popped -1, i))

                clue = csp.row_clues[popped - 1]
                valid_arrangments = get_valid_arrangements(clue, csp.M)
            else:
                for i in range(csp.N):
                    cells.append((i, -popped - 1))
                clue = csp.col_clues[-popped - 1]
                valid_arrangments = get_valid_arrangements(clue, csp.N)

            good_arrangements = []

            n = len(cells)
            for arragement in valid_arrangments:
                index = 0
                valid = 1
                while(index < n):
                    if(state.assignment[cells[index]] == -1):
                        exist = 0
                        for value in state.domains[cells[index]]:
                            if(value == arragement[index]):
                                exist = 1

                        if(exist == 0):
                            valid = 0
                            break

                    else:
                        if(arragement[index] != state.assignment[cells[index]]):
                            valid = 0
                            break

                    index += 1

                if(valid == 1):
                    good_arrangements.append(arragement)

            if(len(good_arrangements) == 0):
                return (False, all_pruned)
            


            index = -1 
            for cell in cells:
                index += 1
                if(state.assignment[cell] == -1):
                    possible_values = []
                    for arrangement in good_arrangements:
                        if(arrangement[index] not in possible_values):
                            possible_values.append(arrangement[index])

                    possible_values = set(possible_values)

                    should_be_pruned = state.domains[cell] - possible_values

                    if(len(should_be_pruned) == len(state.domains[cell])):
                        return False, all_pruned

                    for tupple in should_be_pruned:
                        all_pruned.append((cell, tupple))
                        state.prune(cell, tupple, logger)

                    if(len(should_be_pruned) != 0):
                        if (popped > 0):
                            if (-(cell[1] + 1)) not in queue:
                                queue.append(-(cell[1] + 1))
                        else:
                            if ((cell[0] + 1)) not in queue:
                                queue.append((cell[0] + 1))

        return True, all_pruned
        
        

    def select_unassigned() -> Cell:
        """MRV cell selection — same as Chapter 3."""
        # YOUR CODE HERE
        
        selected_cell = None
        minimum_domain_size= float('inf')
        for cell in csp.variables:
            if(state.assignment[cell] == -1):
                if (state.num_remaining_values[cell] < minimum_domain_size):
                    minimum_domain_size = state.num_remaining_values[cell]
                    selected_cell = cell
        return selected_cell

    def backtrack() -> bool:
        # YOUR CODE HERE
        
        cell = select_unassigned()
        if cell is None:
            return True

        r, c = cell
        for v in list(state.domains[cell]):
            state.assign(cell, v, csp, logger)
            success, pruned = ac3([ r + 1, -(c + 1)])

            if success:
                if backtrack():
                    return True

            for pc, pv in pruned:
                state.unprune(pc, pv)

            state.assign(cell, -1, csp, logger)

        return False

    success, _ = ac3()
    if not success:
        return False

    return backtrack()

In [15]:
def run_example_ac3(label, row_clues, col_clues, timeout=None):
    import threading

    csp    = build_nonogram_csp(row_clues, col_clues)
    logger = StepLogger()
    state  = MRVState(csp)

    result = {"ok": None, "runtime": None, "timed_out": False}

    def _solve():
        t0 = time.time()
        result["ok"]      = solve_ac3_mrv(csp, state, logger)
        result["runtime"] = time.time() - t0

    thread = threading.Thread(target=_solve, daemon=True)
    thread.start()
    thread.join(timeout)

    if thread.is_alive():
        result["timed_out"] = True
        result["runtime"]   = timeout

    num_assigns    = sum(1 for e in logger.events if e.action == "assign")
    num_prunes     = sum(1 for e in logger.events if e.action == "prune")
    num_backtracks = sum(1 for e in logger.events if e.action == "backtrack")

    print(f"\n{label}")
    if result["timed_out"]:
        print(f"Solved:      TIMED OUT after {timeout}s")
    else:
        print(f"Solved:      {result['ok']}")
    print(f"Runtime:     {result['runtime']:.3f} seconds")
    print(f"Assignments: {num_assigns}")
    print(f"Prunes:      {num_prunes}")
    print(f"Backtracks:  {num_backtracks}")

    return csp, logger


csp1_ac3, logger1_ac3 = run_example_ac3("First Example (15×15)", ROW_CLUES_1, COL_CLUES_1)

csp2_ac3, logger2_ac3 = None, None
if RUN_SECOND_EXAMPLE:
    csp2_ac3, logger2_ac3 = run_example_ac3("Second Example (15×20)", ROW_CLUES_2, COL_CLUES_2)



First Example (15×15)
Solved:      True
Runtime:     0.380 seconds
Assignments: 226
Prunes:      172
Backtracks:  1

Second Example (15×20)
Solved:      True
Runtime:     0.889 seconds
Assignments: 300
Prunes:      300
Backtracks:  0


In [16]:
make_animation(csp1_ac3, logger1_ac3, fps=5, last_k=150, stride=1)

if csp2_ac3 is not None:
    make_animation(csp2_ac3, logger2_ac3, fps=5, last_k=150, stride=1)

Discuss your results. Did AC-3 improve runtime compared to MRV alone? Is AC-3 always beneficial? What are its tradeoffs?


`Your Answer:`

همانطور که می بینیم این روش با اینکه باز هم باعث بهبود تعداد بک ترک ها و تعداد اساینمنت ها شده ولی با این حال از لحاظ زمانی تقریبا در همان حدود روش قبل باقی مانده و حتی کمی بدتر هم شده است.

همیشه استفاده از الگوریتم های آرک کانسیستنی ۳ باعث بهبود ران تایم نمی شوند چرا که درست است که باعث کاهش تعداد بک ترک ها می شوند و از فوروارد چکینگ بسیار قوی تر هستند ولی برقراری شرط آرک کانسیستنسی و چک کردن آن سربار بسیار بالایی دارد و در هر مرجله باید کلی از دامنه ها بروزرسانی شوند. که ممکن است بیشتر شدن تعداد هرس ها با اسن روش، آنقدر زیاد نباشد که بتواند این هزینه ی سربار را جبران کند و سرجمع باعث کاهش سرعت حل مسئله شوند.


الگوریتم ای سی تری همیشه کمک کننده نخواهد بود چرا که همانطور که توضیح دادیم چک کردن شروط آرک کانسیستنسی هزینه ی سربار بسیار بالایی دارد. مثلا اگر تعداد نحدودیت کم باشد یا زیاد محدود کننده نباشند، استفاده از این الگوریتم باعث می شود که هر سری تعداد زیادی آرک را چک کنیم بدون اینکه دامنه ها تغییر خاصی کنند. همچنین ممکن است فرایند اضافه کردن از به صف و لوپ اجرای چک کردن شرط آرک کانسیستنسی زیادی طول بکشد و هزینه ی سربار بسیار بالا برود.

پس در کل حالت های بسیار زیادی یافت می شوند که تعداد هرس های اتفاق افتاده به اندازه ای نیستند که بتوانند هزینه ی سربار بالای الگوریتم ای سی تری را جبران کنند و رانتایم را بهبود بدهند. بنابراین استفاده از این الگوریتم همیشه سودمند نیست.

همانطور که در توضیحات قبلی هم بار ها اشاره کردیم، ترید آف هایی بین هزینه ی سربار چک کردن شروط آرک کانسیستنسی و هرس ها وجود دارد که بسیار مهم است.
استفاده از صف و حافظه ی زیاد برای هر مرحله ی این الگوریتم دیگر تریدآفی است که باید به آن توجه کرد. یک ترید آف دیگر وجود باتلنک در مسئله است. این گلوگاه ها می توانند باعث شوند که تعداد هرس ها به طور وحشتناکی زیاد شوند ولی اگر وجود نداشته باشند، ما برای تعداد زیادی گره، هزینه ی بررسی زیادی می دهیم. پس باید باتلنک مناسبی وجود داشته باشد که باعث شود برای تعداد رئوس کمی هزینه ی چک کردن شروط ای سی را بدهیم.